# setup

In [1]:
import os
import sys
sys.path.insert(0,'/root/eallmancy')
sys.path.insert(0,'/root/eallmancy/experiments')
os.chdir('/root/eallmancy')

# TODO: THIS IS ULTRA HACKY, PUT API SETTINGS IN CONTROL PANEL
with open('/root/openai_api_key') as f:
    os.environ['OPENAI_API_KEY'] = f.read().replace('\n','')
with open('/root/gemini_api_key') as f:
    os.environ['GEMINI_API_KEY'] = f.read().replace('\n','')

from eallmancy.engine.llm_solution_engine_v3 import EngineV3
from eallmancy import Artifact
from eallmancy import SinglePartSolution, ProblemSpec
from eallmancy.engine.engine_trace import EngineTrace
from collections import defaultdict
import datetime
import numpy as np
import os
import re




In [2]:
CHATGPT_4OMINI_API = dict(
            host="api.openai.com",
            key=os.environ.get('OPENAI_API_KEY'),
            model="gpt-4o-mini",
            timeout=20
        )

GEMINI_25FLASH_API = dict(
            base_url='https://generativelanguage.googleapis.com/v1beta',
            api_key=os.environ.get('GEMINI_API_KEY'),
            model='gemini-2.0-flash',
            timeout=20,
            openai_format=True
        )

## v0 built-in traceanalysis utils

In [3]:
from eallmancy.analysis.trace_analysis import TraceAnalysis
from copy import copy, deepcopy

def apply_analysis_proto(original_trace, trace_analysis_obj=None, trace_analysis_class=TraceAnalysis, **kwargs):
    
    new_trace = EngineTrace(problem_spec=trace_res.problem_spec)
    if trace_analysis_obj is not None:
        new_trace.trace_analysis = trace_analysis_obj
    else:
        new_trace.trace_analysis = (
            trace_analysis_class(
                ps=original_trace.problem_spec,
                idea_extractor_llm=CHATGPT_4OMINI_API,
                **kwargs
            )
        )
    
    for art in original_trace.list:
        new_art = copy(art)
        new_art.trace_id = None
        parent_arts = [trace_res[pn] for pn, _ in original_trace.graph.in_edges(art.trace_id)]
        new_trace.register_artifact(new_art, parent_arts)
    
    return new_trace


def _iterate_analysis(new_art, trace, last_trace_analysis):
    new_trace = EngineTrace(problem_spec=trace_res.problem_spec)
    new_trace.trace_analysis = deepcopy(last_trace_analysis)
    new_art = copy(new_art)
    new_art.trace_id = None
    parent_arts = [trace_res[pn] for pn, _ in original_trace.graph.in_edges(art.trace_id)]
    new_trace.register_artifact(new_art, parent_arts)
    return new_trace.trace_analysis
    
    

def simulate_analysis(original_trace, current_trace, start_art=None, end_art=None):
    
    new_trace = copy(current_trace)
    new_trace.trace_analysis = deepcopy(current_trace.trace_analysis)
    

    for art in original_trace.list:
        if start_art is not None and art.trace_id < start_art:
            continue
        if end_art is not None and art.trace_id >= end_art:
            break
        new_art = copy(art)
        new_art.trace_id = None
        parent_arts = [original_trace[pn] for pn, _ in original_trace.graph.in_edges(art.trace_id)]
        new_trace.register_artifact(new_art, parent_arts)
    
    return new_trace


In [4]:

def simulate_analysis_history(original_trace, stepsize=20, max_trace_id=None):
    
    trace_cache = dict()
    
    curr_trace = EngineTrace(problem_spec=original_trace.problem_spec, trace_analysis=True, idea_extractor_llm=CHATGPT_4OMINI_API,)
    
    last_idx = 0
    for idx in range(stepsize, min(max_trace_id, len(original_trace.list)), stepsize):
        curr_trace = trace_cache[idx] = simulate_analysis(original_trace, curr_trace, start_art=last_idx, end_art=idx)
        last_idx = idx
    else:
        if last_idx < len(original_trace.list):
            curr_trace = trace_cache[max_trace_id or len(original_trace.list)] = simulate_analysis(original_trace, curr_trace, start_art=last_idx, end_art=max_trace_id)
    
    return trace_cache

## testing insane overwrite

In [5]:

import polars as pl
import plotly.express as px

def trace_dist_matrixes(trace, **dist_funcs):
    "dist_func needs to take two artifacts and figure out the rest"
    
    idx_to_soln = {idx:_a for idx,_a in enumerate([a for a in trace.list if a.is_solution])}
    
    _plotrows = []
    for a in range(len(idx_to_soln)):
        for b in range(len(idx_to_soln)):
            sa = idx_to_soln[a]
            sb = idx_to_soln[b]
            e = dict(
                a_idx=a,
                b_idx=b,
                a_tidx=idx_to_soln[a].trace_id,
                b_tidx=idx_to_soln[b].trace_id,
                dist=0,
                a_fit=sa.fitness,
                b_fit=sb.fitness
            )
            if a==b:
                for k,_ in dist_funcs.items():
                    e[f'dist_{k}'] = 0
            else:
                for k,dist_func in dist_funcs.items():
                    e[f'dist_{k}'] = dist_func(sa, sb)
            _plotrows.append(e)
    _plotdf = pl.DataFrame(_plotrows)
    return _plotdf

def trace_dist_matrix(trace, dist_func):
    _plotdf = trace_dist_matrixes(trace, func=dist_func)
    return _plotdf.with_columns(dist=pl.col.dist_func).drop('dist_func')

def plot_trace_dist_matrix(trace, dist_func, _plotdf=None):
    if _plotdf is None:
        _plotdf = trace_dist_matrix(trace, dist_func)
    
    fig = px.scatter(
        _plotdf,
        x='a_idx',
        y='b_idx',
        color='dist',
        height=700,width=700
    )
    fig.update_layout(coloraxis_reversescale=True)
    fig.update_traces(marker_symbol="square")
    return fig

# trace_dist_matrix(original_trace, ta.distance)

## diversity, fitness 'modeling'

In [6]:
def shannon_wiener_clusters(arts, dist_func, thresh=0.1, max_trace_id=None):
    clusters = [] # list of list of artifacts

    for a in arts:
        if not a.is_solution:
            continue

        if max_trace_id is not None:
            if a.trace_id > max_trace_id:
                continue

        for c_idx, cl in enumerate(clusters):
            if any([dist_func(a, mem) > thresh for mem in cl]):
                continue  # someone broke similarity threshold
            clusters[c_idx].append(a)
            break
        else:
            clusters.append([a])  # new cluster
    return clusters

def shannon_wiener_probs(arts, *args, **kwargs):
    clusters = shannon_wiener_clusters(arts, *args, **kwargs)
    num_solns = sum([len(c) for c in clusters])
    return [len(c)*1.0/num_solns for c in clusters]

def shannon_wiener_diversity(arts, *args, **kwargs):
    probs = shannon_wiener_probs(arts, *args, **kwargs)
    return sum([-1*p*np.log2(p) for p in probs])

In [7]:

import networkx as nx


def cdi(arts, dist_func, max_trace_id=None):
    # clone trace graph up until max_trace_id, throwing away non-solutions

    solns = [a for a in arts if a.is_solution]
    if max_trace_id is not None:
        solns = [a for a in solns if a.trace_id <= max_trace_id]
    tmpG = nx.Graph()
    for a in solns:
        for b in solns:
            if a.trace_id >= b.trace_id:
                continue
            tmpG.add_edge(a.trace_id, b.trace_id, weight=dist_func(a,b))

    # construct minimium spanning tree
    mst_edge_weights = [d['weight'] for _, _, d in nx.minimum_spanning_edges(tmpG, data=True, weight="weight")]

    # probs as edge % of total weights
    total_mst_weight = sum(mst_edge_weights)
    mst_edge_probs = [ew*1.0/total_mst_weight for ew in mst_edge_weights]

    # calc entropy
    return sum([-1*p*np.log2(p) for p in mst_edge_probs])


In [8]:

import polars as pl
import plotly.express as px
from eallmancy.analysis.analyzer.analyzer import Analyzer


def top_k_generator(idx_to_soln_map, k=10):
    topk_cache = []
    for i in range(max(idx_to_soln_map.keys())):
        topk_cache.append(idx_to_soln_map[i])
        if len(topk_cache) > k:
            topk_cache = list(sorted(topk_cache, key=lambda a: a.fitness, reverse=True))[:k]
        yield i, topk_cache


def _plotdf_v9(trace):
    
    ta = Analyzer.build_analysis(trace, trace.problem_spec)
    idx_to_soln = {idx:_a for idx,_a in enumerate([a for a in trace.list if a.is_solution])}
    
    _plot_rows=[]
    _all_so_far = []
    for i, topk_cache in top_k_generator(idx_to_soln, k=10):
        _all_so_far.append(idx_to_soln[i])
        ee = dict(
            idx=i,
            g_cdi=cdi(topk_cache, ta.distance),
            h_cdi=cdi(_all_so_far, ta.distance),
            g_swdi=shannon_wiener_diversity(topk_cache, ta.distance),
            h_swdi=shannon_wiener_diversity(_all_so_far, ta.distance),
            best_so_far=max([a.fitness for a in _all_so_far]),
            fitness=idx_to_soln[i].fitness,
        )
        ee['is_breakthrough'] = ee['fitness'] == ee['best_so_far']
        _plot_rows.append(ee)
    _plotdf = pl.DataFrame(_plot_rows)
    return _plotdf


In [9]:
from eallmancy.analysis.analyzer.utils import get_codet5p_embeddings, get_openai_embeddings, cosine_sim

class PureEmbeddingAnalysis:
    def __init__(self, trace, embedding_func):
        all_solns = [a.trace_id for a in trace.list if a.is_solution]
        embs = embedding_func([CodeT5PAnalysis.get_clean_program(trace[ti]) for ti in all_solns])
        self.embs = {
            ti: emb for ti, emb in zip(all_solns, embs)
        }

    @classmethod
    def get_clean_program(cls, arte):
        return cls._clean_program(arte.program)
        
    @classmethod
    def _clean_program(cls, prog):
        # find function line
        fsig_idx = prog.find('def ')
        programbody_idx = fsig_idx + prog[fsig_idx:].find('\n')+1
        return prog[programbody_idx:]
        
    def distance(self, a, b):
        return 1 - cosine_sim(self.embs[a.trace_id], self.embs[b.trace_id])
        
class CodeT5PAnalysis(PureEmbeddingAnalysis):
    def __init__(self, trace):
        super().__init__(trace, embedding_func=get_codet5p_embeddings)
        
class OpenAIAnalysis(PureEmbeddingAnalysis):
    def __init__(self, trace):
        super().__init__(trace, embedding_func=get_openai_embeddings)

## distance vs fitness stuff

In [10]:
%%time
import glob
import pickle as pk

_plotdfs = []
for tid, tracepk in enumerate(glob.glob('/root/elmcy_reevo_traces/*.pk')):
    # if not 'op_aco' in tracepk:
    #     continue
    print('loading',tracepk)
    problem = tracepk[tracepk.rfind('reevo_')+6:tracepk.rfind('.pk')]
    trace = EngineTrace.load(tracepk)
    tb = CodeT5PAnalysis(trace)
    tc = OpenAIAnalysis(trace)
    # ta = Analyzer.build_analysis(trace, trace.problem_spec)
    with open(tracepk.replace('elmcy_reevo_traces', 'elmcy_reevo_analyses'), 'rb') as f:
        ta = pk.load(f)
    dd = trace_dist_matrixes(
            trace,
            elmcy=ta.distance,
            jplag=lambda a,b : ta.distance(a, b, use_cosim=False),
            codet5p=tb.distance,
            openai=tc.distance,
        
        ).with_columns(problem=pl.lit(problem))
    del ta
    del tb
    del tc
    # dd = trace_dist_matrix(trace, ta.distance)
    _plotdfs.append(dd)
    print('    loaded!')
_plotdf = pl.concat([ppd.with_columns(sim_idx=pl.lit(did)) for did, ppd in enumerate(_plotdfs)])


loading /root/elmcy_reevo_traces/20250802-235310_a266_reevo_op_aco.pk
    loaded!
loading /root/elmcy_reevo_traces/20250803-010854_7f89_reevo_op_aco.pk
    loaded!
loading /root/elmcy_reevo_traces/20250803-013958_8849_reevo_tsp_aco.pk
    loaded!
loading /root/elmcy_reevo_traces/20250802-235352_c6cb_reevo_op_aco.pk
    loaded!
loading /root/elmcy_reevo_traces/20250803-002048_663d_reevo_tsp_aco.pk
    loaded!
loading /root/elmcy_reevo_traces/20250803-010407_f23e_reevo_tsp_aco.pk
    loaded!
loading /root/elmcy_reevo_traces/20250803-015601_2e2b_reevo_cvrp_aco.pk
    loaded!
loading /root/elmcy_reevo_traces/20250803-020128_2611_reevo_cvrp_aco.pk
    loaded!
loading /root/elmcy_reevo_traces/20250802-235331_c803_reevo_op_aco.pk
    loaded!
loading /root/elmcy_reevo_traces/20250803-002027_2a2c_reevo_tsp_aco.pk
    loaded!
loading /root/elmcy_reevo_traces/20250803-011402_e009_reevo_op_aco.pk
    loaded!
loading /root/elmcy_reevo_traces/20250803-013004_c0d9_reevo_op_aco.pk
    loaded!
loading 

In [11]:
print(2)

2


In [13]:
#_plotdf.write_csv('_plotdf.csv')

In [12]:

def dist_regularised(dist_col):
    return pl.col(dist_col) / pl.col(dist_col).max().over(['problem'])

fig = px.box(
    (
        _plotdf
        .filter(pl.col.a_fit != pl.lit(-float('inf')))
        .filter(pl.col.b_fit != pl.lit(-float('inf')))
        .with_columns(delta_fit=pl.col.a_fit - pl.col.b_fit)
        .with_columns(dist_bin=(dist_regularised('dist_jplag')/0.1).round()*0.1)
    ),
    x='dist_bin',
    y='delta_fit',
    facet_row='problem',
    color='problem',
    height=1000,
    # box=True,
    points=False,
    # color='sim_idx'
)
# fig.update_traces(showwhiskers=False)  # no whiskers (min/max), just Q1–Q3 + median
fig.update_yaxes(matches=None)

In [13]:

def dist_regularised(dist_col):
    return pl.col(dist_col) / pl.col(dist_col).max().over(['problem'])

fig = px.box(
    (
        _plotdf
        .filter(pl.col.a_fit != pl.lit(-float('inf')))
        .filter(pl.col.b_fit != pl.lit(-float('inf')))
        .with_columns(delta_fit=pl.col.a_fit - pl.col.b_fit)
        # .with_columns(dist_bin=(dist_regularised('dist_openai')/0.1).round()*0.1)
        .with_columns(dist_bin=(pl.col('dist_openai')/0.1).round()*0.1)
    ),
    x='dist_bin',
    y='delta_fit',
    facet_row='problem',
    color='problem',
    height=1000,
    # box=True,
    points=False,
    # color='sim_idx'
)
# fig.update_traces(showwhiskers=False)  # no whiskers (min/max), just Q1–Q3 + median
fig.update_yaxes(matches=None)

In [56]:

def dist_regularised(dist_col):
    return pl.col(dist_col) / pl.col(dist_col).max().over(['problem'])

fig = px.box(
    (
        _plotdf
        .filter(pl.col.a_fit != pl.lit(-float('inf')))
        .filter(pl.col.b_fit != pl.lit(-float('inf')))
        .with_columns(delta_fit=pl.col.a_fit - pl.col.b_fit)
        .with_columns(dist_bin=(dist_regularised('dist_codet5p')/0.1).round()*0.1)
    ),
    x='dist_bin',
    y='delta_fit',
    facet_row='problem',
    color='problem',
    height=1000,
    # box=True,
    points=False
    # color='sim_idx'
)
# fig.update_traces(showwhiskers=False)  # no whiskers (min/max), just Q1–Q3 + median
fig.update_yaxes(matches=None)


In [21]:

def dist_regularised(dist_col):
    return pl.col(dist_col) / pl.col(dist_col).max().over(['problem'])

fig = px.box(
    (
        _plotdf
        .filter(pl.col.a_fit != pl.lit(-float('inf')))
        .filter(pl.col.b_fit != pl.lit(-float('inf')))
        .with_columns(delta_fit=pl.col.a_fit - pl.col.b_fit)
        .with_columns(dist_bin=(dist_regularised('dist_elmcy')/0.1).round()*0.1)
    ),
    x='dist_bin',
    y='delta_fit',
    facet_row='problem',
    color='problem',
    height=1000,
    # box=True,
    points=False
    # color='sim_idx'
)
# fig.update_traces(showwhiskers=False)  # no whiskers (min/max), just Q1–Q3 + median
fig.update_yaxes(matches=None)


## rolling top-K diversity, historical diversity, fitness improvement modelling

In [98]:
trace = original_trace
idx_to_soln = {idx:_a for idx,_a in enumerate([a for a in trace.list if a.is_solution])}

import polars as pl
import plotly.express as px


def top_k_generator(idx_to_soln_map, k=10):
    topk_cache = []
    for i in range(max(idx_to_soln.keys())):
        topk_cache.append(idx_to_soln[i])
        if len(topk_cache) > k:
            topk_cache = list(sorted(topk_cache, key=lambda a: a.fitness, reverse=True))[:k]
        yield i, topk_cache

_plot_rows=[]
_all_so_far = []
for i, topk_cache in top_k_generator(idx_to_soln, k=10):
    _all_so_far.append(idx_to_soln[i])
    ee = dict(
        idx=i,
        g_cdi=cdi(topk_cache, ta.distance),
        h_cdi=cdi(_all_so_far, ta.distance),
        g_swdi=shannon_wiener_diversity(topk_cache, ta.distance),
        h_swdi=shannon_wiener_diversity(_all_so_far, ta.distance),
        best_so_far=max([a.fitness for a in _all_so_far]),
        fitness=idx_to_soln[i].fitness,
    )
    ee['is_breakthrough'] = ee['fitness'] == ee['best_so_far']
    _plot_rows.append(ee)
_plot_df = pl.DataFrame(_plot_rows)

In [26]:
fig = px.line(
    (
        _plotdf.filter(pl.col.idx>5).sort('h_swdi')
    ),
    x='h_swdi',
    y='best_so_far',
    line_group='sim_idx'
)
fig

In [22]:
fig = px.line(
    (
        _plotdf.unpivot(index=['sim_idx', 'idx'])
        .with_columns(
            fitwin=pl.when(pl.col.variable.is_in(['best_so_far']))
                        .then(pl.lit('bfit'))
                        .when(pl.col.variable=='fitness')
                        .then(pl.lit('fit'))
                        .otherwise(pl.lit('div'))
        )
        # .filter(pl.col.variable!='fitness')
    ),
    x='idx',
    y='value',
    color='variable',
    facet_row='fitwin',
    line_group='sim_idx'
)
fig.update_yaxes(matches=None)